In [1]:
import hail as hl

In [56]:
# Add imports/function for plotting and viewing results of subpop assignment
from typing import List, Tuple

from gnomad.sample_qc.ancestry import POP_COLORS
from gnomad.utils.plotting import *
from gnomad_qc.v3.resources.basics import get_checkpoint_path
from gnomad_qc.v3.resources.meta import meta
from gnomad_qc.v3.sample_qc.sample_qc import assign_pops

import bokeh.plotting as bpl

from bokeh.layouts import row, column, gridplot
from bokeh.models.annotations import LegendItem, ColorBar
from bokeh.models.mappers import CategoricalColorMapper, ColorMapper
from bokeh.models.plots import Plot
from bokeh.plotting import figure, output_notebook, show
from bokeh.palettes import Spectral6
from bokeh.models.renderers import Renderer
from IPython.core.display import display, HTML


def plot_precision_recall(results_ht: hl.Table):
    """
    Plot precision recall curve.

    :param results_ht: Table containing precision/recall results, numbers of true positives, false positives, and false negatives
    :return: Tabs containing plotted precision/recall results according to various min_prob and max_proportion_mislabeled_training_samples parameters
    """
    tabs = []
    # Plot colored by min_prob
    MIN_PROB_COLORS = {}
    MIN_PROB_COLORS["1.00000e-01"] = "#941494"
    MIN_PROB_COLORS["2.00000e-01"] = "#a9a9a9"
    MIN_PROB_COLORS["3.00000e-01"] = "#4363d8"
    MIN_PROB_COLORS["4.00000e-01"] = "#f58231"
    MIN_PROB_COLORS["5.00000e-01"] = "#42d4f4"
    MIN_PROB_COLORS["6.00000e-01"] = "#f032e6"
    MIN_PROB_COLORS["7.00000e-01"] = "#bfef45"
    MIN_PROB_COLORS["7.50000e-01"] = "#fabed4"
    MIN_PROB_COLORS["8.00000e-01"] = "#469990"
    MIN_PROB_COLORS["8.50000e-01"] = "#e6194B"
    MIN_PROB_COLORS["9.00000e-01"] = "#000075"
    MIN_PROB_COLORS["9.50000e-01"] = "#dcbeff"

    min_prob_colors = MIN_PROB_COLORS
    min_prob_colormap = CategoricalColorMapper(
        factors=list(min_prob_colors.keys()), palette=list(min_prob_colors.values())
    )

    tabs = []
    results_ht = results_ht.annotate(min_prob=hl.str(results_ht.min_prob))
    plot = hl.plot.scatter(
        results_ht.recall,
        results_ht.precision,
        xlabel="Recall",
        ylabel="Precision",
        hover_fields={
            "min_prob": results_ht.min_prob,
            "max_proportion_mislabeled_training_samples": results_ht.max_proportion_mislabeled_training_samples,
            "TP": results_ht.TP,
            "FP": results_ht.FP,
            "FN": results_ht.FN,
        },
        label={"min_prob": results_ht["min_prob"]},
        colors={
            "min_prob": min_prob_colormap,
        },
        collect_all=True,
        size=6,
    )

    plot.xaxis.axis_label_text_font_size = "20pt"
    plot.yaxis.axis_label_text_font_size = "20pt"
    plot.legend.label_text_font_size = "20pt"
    plot.plot_height = 500
    plot.plot_width = 950

    tabs.append(Panel(title="color_min_prob", child=plot))

    return tabs


def plot_pcs(
    ht: hl.Table,
    pca_scores_expr,
    pcs: List[Tuple],
    label: str,
    pop_colormap,
    collect_all: bool,
):
    """
    Plot PCS colored by 'label'.

    :param ht: Table containing assigned populations/subpopulations
    :param pca_scores_expr: Expression in Table containing the PCA scores
    :param pcs: List of Tuples containing PC pairs to plot
    :param label: Name of field to use for coloring
    :param pop_colormap: bokeh.models.mappers.CategoricalColorMapper containing mapping of label names to label colors
    :return: Tabs containing plotted PCAs
    """
    tabs = []
    for pc_i, pc_j in pcs:
        index_pc_i = hl.eval(ht.pcs).index(pc_i)
        index_pc_j = hl.eval(ht.pcs).index(pc_j)
        plot = hl.plot.scatter(
            pca_scores_expr[index_pc_i],
            pca_scores_expr[index_pc_j],
            xlabel=f"PC{pc_i}",
            ylabel=f"PC{pc_j}",
            label={
                f"{label}": ht[f"{label}"],
            },
            hover_fields={
                "s": ht.s,
                "training_pop": ht.training_pop,
                "subpop": ht.subpop,
                "subpop_description": ht.subpop_description,
                "research_project": ht.research_project,
                "project_id": ht.project_id,
                "kin": ht.kin,
            },
            collect_all=collect_all,
            colors={
                f"{label}": pop_colormap,
            },
        )

        plot.xaxis.axis_label_text_font_size = "20pt"
        plot.yaxis.axis_label_text_font_size = "20pt"
        plot.legend.label_text_font_size = "20pt"
        plot.plot_height = 500
        plot.plot_width = 950

        tabs.append(Panel(title=f"PC{pc_i}/PC{pc_j}", child=plot))
    return Tabs(tabs=tabs)


def show_bokeh(plot_fig):
    try:
        bpl.reset_output()
        bpl.output_notebook()
        bpl.show(plot_fig)
    except:
        bpl.output_notebook()
        bpl.show(plot_fig)

# Set main parameters for plotting precision/recall

In [3]:
pop = "amr"
include_unreleasable_samples = False
high_quality = True

# Plot precision/recall curve


In [52]:
file_path = get_checkpoint_path(
    "subpop_analysis/parameter_testing_{}{}{}".format(
        pop,
        "_with_unreleasable_samples" if include_unreleasable_samples else "",
        ".high_quality" if high_quality else "",
    )
)

results_ht = hl.read_table(file_path)

tabs = plot_precision_recall(results_ht)
show_bokeh(Tabs(tabs=tabs))

Loading BokehJS ...

# View results table for precision/recall

In [54]:
results = results_ht.to_pandas()
results

,min_prob,max_proportion_mislabeled_training_samples,percent_correct,TP,FP,FN,error_rate,precision,recall
0,0.10,1.0,97.749648,695,16,0,0.022504,0.977496,1.000000
1,0.20,1.0,97.749648,695,16,0,0.022504,0.977496,1.000000
2,0.30,1.0,97.609001,694,16,1,0.022504,0.977465,0.998561
3,0.40,1.0,97.468354,693,15,3,0.022504,0.978814,0.995690
4,0.50,1.0,96.483826,686,13,12,0.022504,0.981402,0.982808
5,0.60,1.0,94.374121,671,8,32,0.022504,0.988218,0.954481
6,0.70,1.0,91.842475,653,5,53,0.022504,0.992401,0.924929
7,0.75,1.0,90.014065,640,4,67,0.022504,0.993789,0.905233
8,0.80,1.0,87.904360,625,1,85,0.022504,0.998403,0.880282
9,0.85,1.0,85.794655,610,0,101,0.022504,1.000000,0.857947


# Set main parameters for plotting PCs

In [55]:
pop = "amr"
min_prob = 0.80
max_proportion_mislabeled_training_samples = 1
pcs = [1, 2, 3, 4, 5, 6, 7, 8, 9, 10, 11, 12, 13, 14, 15, 16, 17, 18, 19, 20]
include_unreleasable_samples = False
high_quality = True
withhold_prop = None

# Plot PCs


In [63]:
# Set subcolors
POP_COLORS["African-American"] = "#941494"
POP_COLORS["NA"] = "#a9a9a9"
POP_COLORS["asw"] = "#4363d8"
POP_COLORS["Colombian"] = "#f58231"
POP_COLORS["Costa Rican"] = "#42d4f4"
POP_COLORS["Hawaiian"] = "#f032e6"
POP_COLORS["Karitiana"] = "#bfef45"
POP_COLORS["Maya"] = "#fabed4"
POP_COLORS["Mexican-American"] = "#469990"
POP_COLORS["Indigenous American"] = "#e6194B"
POP_COLORS["Dutch"] = "#000075"
POP_COLORS["Peruvian"] = "#dcbeff"
POP_COLORS["Pima"] = "#800000"
POP_COLORS["Puerto Rican"] = "#aaffc3"
POP_COLORS["Surui"] = "#ffd8b1"

In [64]:
# Run assign_pops with the given parameters
joint_pca_ht, joint_pca_fit = assign_pops(
    min_prob=min_prob,
    max_proportion_mislabeled_training_samples=max_proportion_mislabeled_training_samples,
    include_unreleasable_samples=False,
    pcs=pcs,
    withhold_prop=withhold_prop,
    pop=pop,
    high_quality=high_quality,
    missing_label="Other",
)

# Add on metadata annotations
meta_ht = meta.ht().drop("high_quality")

meta_ht = meta_ht.select(
    meta_ht.project_meta.subpop_description,
    meta_ht.project_meta.research_project,
    meta_ht.project_meta.project_id,
)

ht = joint_pca_ht.annotate(**meta_ht[joint_pca_ht.key])
ht = ht.annotate(kin=hl.null(hl.tarray(hl.tfloat)))

# Filter to just evaluation samples
evaluation_ht = ht.filter(ht.evaluation_sample)

INFO (sample_qc 528): Assigning global population/subpopulation labels
INFO (sample_qc 594): Running RF using 3553 training examples


Random forest feature importances are as follows: [0.06997308 0.07591089 0.20486611 0.16611941 0.05093131 0.047541
 0.06230065 0.10802387 0.08125397 0.02172845 0.00966651 0.01401451
 0.01378806 0.01142784 0.01070612 0.0074647  0.01163552 0.00864474
 0.01537168 0.00863156]
Estimated error rate for RF model is 0.023909985935302358


INFO (gnomad.sample_qc.ancestry 230): Found the following sample count after population assignment: Mexican-American: 408, Other: 3632, Hawaiian: 86, Costa Rican: 3050, Maya: 25, Indigenous American: 247, Puerto Rican: 610, Colombian: 179, Peruvian: 196, Surui: 5, Karitiana: 7, Pima: 10
<ipython-input-64-7a8ebcee217d>:21: DeprecationWarning: Call to deprecated function (or staticmethod) null. (Replaced by hl.missing) -- Deprecated since version 0.2.62.
  ht = ht.annotate(kin = hl.null(hl.tarray(hl.tfloat)))


In [66]:
pop_colors = POP_COLORS
pop_colormap = CategoricalColorMapper(
    factors=list(pop_colors.keys()), palette=list(pop_colors.values())
)

show_bokeh(
    plot_pcs(
        ht,
        ht.pca_scores,
        pcs=[(a, a + 1) for a in range(1, 20, 2)],
        label="subpop",
        pop_colormap=pop_colormap,
        collect_all=True,
    )
)

2022-05-31 15:43:46 Hail: INFO: Coerced sorted dataset
2022-05-31 15:43:59 Hail: INFO: Coerced sorted dataset
2022-05-31 15:44:11 Hail: INFO: Coerced sorted dataset
2022-05-31 15:44:23 Hail: INFO: Coerced sorted dataset
2022-05-31 15:44:35 Hail: INFO: Coerced sorted dataset
2022-05-31 15:44:47 Hail: INFO: Coerced sorted dataset
2022-05-31 15:44:59 Hail: INFO: Coerced sorted dataset
2022-05-31 15:45:11 Hail: INFO: Coerced sorted dataset
2022-05-31 15:45:23 Hail: INFO: Coerced sorted dataset
2022-05-31 15:45:36 Hail: INFO: Coerced sorted dataset


Loading BokehJS ...

# Show confusion matrix

In [ ]:
pop_pd = ht.to_pandas()
pop_comparison = pd.crosstab(pop_pd["subpop_description"], pop_pd["subpop"])
pop_comparison

2022-05-31 15:45:44 Hail: INFO: Coerced sorted dataset
